In [50]:
import numpy as np
import matplotlib.pyplot as plt
import matplotlib.animation as animation
from IPython.display import HTML

For an object with mass $m$ and moment of inertia matrix $\mathrm{I}_p$ about a pivot which has velocity $\mathbf{v}_p$, where the displacement from the pivot to the center of mass is $\mathbf{r}_{\text{pivot} \rightarrow \text{com}}$, and the object is rotating with angular velocity $\omega$ about the pivot, the kinetic energy is
$$
T = \frac{1}{2} m \mathbf{v}^2_p + m \mathbf{v}_p \cdot (\mathbf{\omega} \times \mathbf{r}_{\text{pivot} \rightarrow \text{com}}) + \frac{1}{2}\mathbf{\omega} \cdot \mathrm{I}_p \mathbf{\omega} .
$$

We set $\omega = \dot{\theta} \hat{k}$, so the only important component of moment of inertia is $I = \mathrm{I}_{p, 3,3}$. We also get $\mathbf{r}_{\text{pivot} \rightarrow \text{com}} = \dot\theta l \hat\theta$ where $l$ is the distance from the pivot to the center of mass. We also have the pivot's velocity only in the $\hat{j}$ direction and we call its magnitude $\dot{d}$.

We therefore have
$$
T = \frac{1}{2} m \dot{d}^2 + ml\dot{d}\dot\theta \sin\theta + \frac{1}{2}I\dot{\theta}^2 .
$$

For potential energy, we get
$$
V = mgy = mg(d-l\cos\theta) .
$$

Plugging these into the Euler-Lagrange equation, we get
$$
\ddot\theta + \frac{ml}{I} (g-\ddot{d})\sin\theta = 0 .
$$
Let's define $\lambda = \frac{I}{ml}$ as the effective length of the pendulum. It acts like the length does in a simple pendulum with a point mass on a massless rod.

In [51]:
def angular_acceleration(eff_length, gravity, pivot_acc, theta):
    return -np.sin(theta) * (gravity - pivot_acc) / eff_length


def pivot_acceleration(amplitude, frequency, t):
    return -amplitude * frequency * frequency * np.cos(frequency * t)

In [52]:
def yoshida_4th_step(q, p, t, dt, get_force, get_velocity):
  """General 4th-Order Yoshida symplectic integrator step."""
  w1 = 1.0 / (2.0 - 2.0 ** (1.0 / 3.0))
  w0 = -(2.0 ** (1.0 / 3.0)) / (2.0 - 2.0 ** (1.0 / 3.0))

  d = [w1, w0, w1, 0.0]

  curr_q, curr_p = q, p
  curr_t = t

  for i in range(4):
    dt_sub = d[i] * dt
    p_half = curr_p + 0.5 * dt_sub * get_force(curr_q, curr_t)
    curr_q = curr_q + dt_sub * get_velocity(p_half)
    curr_p = p_half + 0.5 * dt_sub * get_force(curr_q, curr_t + dt_sub)
    curr_t += dt_sub

  return curr_q, curr_p

In [ ]:
g = 9.81
l = 1.0
m = 1.0
I = m * (l**2)
eff_length = I / m / l
A = 0.05
omega = 90.0 # this is set to be just enough to keep it up

In [54]:
def pivot_position(A, omega, t):
  return A * np.cos(omega * t)


def kapitza_velocity(p):
  return p / I # angular momentum divided by moment of inertia


def kapitza_force(theta, t):
  return I * angular_acceleration(
      eff_length, g, pivot_acceleration(A, omega, t), theta
  )

In [55]:
# Simulation parameters
dt = np.min([1 / np.float64(100.0) / omega, 0.001])
t_max = 5.0
steps = int(t_max / dt)
t_steps = np.arange(0, t_max, dt)

# Initial conditions: near the inverted position (theta = pi)
theta_init = np.pi - 0.1
p_init = 0.0

theta_vals = np.zeros_like(t_steps)
th, p = theta_init, p_init

print('Running simulation...')
for i, t in enumerate(t_steps):
  theta_vals[i] = th
  th, p = yoshida_4th_step(th, p, t, dt, kapitza_force, kapitza_velocity)
print('Simulation complete. Generating animation...')


# Animation Setup for Jupyter
fig, ax = plt.subplots(figsize=(6, 6))
ax.set_xlim(-1.5, 1.5)
ax.set_ylim(-1.5, 1.5)
ax.set_aspect('equal')
ax.grid(True)
ax.set_title('Kapitza Pendulum Animation (Inverted Stable State)')

(line,) = ax.plot([], [], 'o-', lw=3, markersize=10, color='royalblue')
time_text = ax.text(
    0.05, 0.9, '', transform=ax.transAxes, fontsize=12, fontweight='bold'
)

# Skip frames to keep playback smooth
frame_skip = max(1, int(0.01 / dt))
frames_to_animate = range(0, len(t_steps), frame_skip)


def init():
  line.set_data([], [])
  time_text.set_text('')
  return line, time_text


def animate(i):
  t = t_steps[i]
  theta = theta_vals[i]

  # Pivot coordinates (moves vertically)
  x_pivot = 0.0
  y_pivot = pivot_position(A, omega, t)

  # Bob coordinates
  x_bob = x_pivot + l * np.sin(theta)
  y_bob = y_pivot - l * np.cos(theta)

  line.set_data([x_pivot, x_bob], [y_pivot, y_bob])
  time_text.set_text(f'Time: {t:.2f} s\nState: Inverted')
  return line, time_text


ani = animation.FuncAnimation(
    fig,
    animate,
    init_func=init,
    frames=frames_to_animate,
    interval=20,
    blit=True,
)

# Close the static plot figure so it doesn't double-render
plt.close(fig)

# Render the interactive HTML animation inside the notebook cell
HTML(ani.to_jshtml())

Running simulation...
Simulation complete. Generating animation...
